# Tutorial - Fluid-Film Bearings


This tutorial covers the fluid-film bearing classes available in ROSS. The journal-bearing classes share a thermo-elasto-hydro-dynamic (TEHD) engine that solves the Reynolds equation coupled with the film energy equation — and, optionally, pad heat conduction and elastic deformation — to find the bearing equilibrium and its stiffness and damping coefficients.

| Class | Bearing type |
|-------|-------------|
| `PlainJournal` | Plain cylindrical journal bearing with axial grooves |
| `PartialArcBearing`, `EllipticalBearing`, `OffsetHalvesBearing`, `MultiLobeBearing`, `PressureDamBearing` | Classic fixed-geometry configurations |
| `FixedGeometryBearing` | Generic fixed-geometry bearing described by per-pad arrays |
| `TiltingPad` | Tilting-pad journal bearing |
| `ThrustPad` | Tilting-pad thrust bearing (dedicated THD solver) |
| `SqueezeFilmDamper` | Squeeze-film damper (analytical short-bearing model) |

All classes inherit from `BearingElement` and can be placed in a `rs.Rotor` assembly exactly like the simpler classes described in the general bearings tutorial.

>**Note**: The journal-bearing classes were rewritten on the shared fluid-film engine in ROSS 2.4. Dynamic coefficients differ from earlier versions (different turbulence model, cavitation treatment and energy equation), and a few solver-tuning parameters were retired — passing them raises a `DeprecationWarning` and they are ignored. See the release notes for the migration guide.
```

# Section 1: PlainJournal

The `PlainJournal` class models plain cylindrical journal bearings whose bore is split into pads by axial oil grooves. For each speed in `frequency`, the engine finds the journal equilibrium position for the applied load and solves the film pressure and temperature fields; the eight stiffness and damping coefficients follow from perturbations of the converged film.

## 1.1 Example of application

To run the test case provided as an example in the documentation of the `PlainJournal` class, use:

In [1]:
import ross as rs
from ross.units import Q_

import plotly.io as pio

pio.renderers.default = "notebook"


plainjournal = rs.PlainJournal(
    n=3,  # Nodal location of the bearing in the FE model of the rotor
    pad_axial_length=0.263144,  # Axial length of the bearing
    journal_diameter=0.4,  # Journal diameter
    radial_clearance=1.95e-4,  # Bearing radial clearance
    total_ex_film=22,  # Circumferential film elements per pad
    total_ez_film=12,  # Axial film elements
    n_pads=2,  # Total number of pads
    pad_arc=Q_(176, "deg"),  # Angular length of the pads
    preload=0,  # Preload factor
    oil_supply_temperature=Q_(50, "degC"),  # Oil supply temperature
    speed=Q_([900, 1200], "RPM"),  # Journal rotational speed
    fxs_load=0,  # External load on the shaft, horizontal direction
    fys_load=-112814.91,  # External load on the shaft, vertical direction
    lubricant="ISOVG32",  # Lubricant type
    oil_flow_v=Q_(30, "l/min"),  # Supplied oil flow
    oil_supply_pressure=0,  # Oil supply pressure
)

The engine obtains the stiffness and damping coefficients by perturbing the converged film around the equilibrium position, so no method selection is needed.

The `operating_type` parameter selects the lubrication condition:

| Option | Meaning |
| --- | --- |
| `"regular_flooded"` (default) | Fully flooded supply |
| `"starved_condition_even"` | Starved supply, evenly distributed |

Under starvation the supplied flow `oil_flow_v` limits how much of each pad is active; with a flooded supply it enters the groove-mixing energy balance together with the hot-oil carryover factor (`hot_oil_lambda`).

## 1.2 Execution time

To display the total time spent solving all speeds specified in `frequency`, use:

In [2]:
plainjournal.show_execution_time()

Execution time: 44.930685 seconds


## 1.3 Pressure and temperature distributions

The `plot_results` method generates the standard set of field plots — 2D contours and 3D surfaces of the film pressure and temperature. The `freq_index` parameter selects which solved speed to visualize; here `freq_index=1` selects 1200 RPM:

In [3]:
plainjournal.plot_results(show_plots=True, freq_index=1);

## 1.4 Film thickness

To display the film thickness profile at the axial mid-plane of the bearing, use:

In [4]:
plainjournal.plot_film_thickness_2d(freq_index=1)

## 1.5 Results summary

To display a per-speed summary of the converged solution — eccentricity, attitude angle, power loss, peak pressure, peak temperature and side flow — use:

In [5]:
plainjournal.show_results()


                                                      FLUID FILM BEARING RESULTS                                                      
+-----------------+------------------+----------------+----------------+-------------------+---------------------+-------------------+
| Frequency [RPM] | Eccentricity [-] | Attitude [deg] | Power loss [W] | Max pressure [Pa] | Max temperature [K] | Side flow [m^3/s] |
+-----------------+------------------+----------------+----------------+-------------------+---------------------+-------------------+
|      900.0      |      0.5938      |      47.1      |      8885      |      2.76e+06     |        345.40       |     0.0003639     |
|      1200.0     |      0.5424      |      50.6      |    1.41e+04    |     2.625e+06     |        347.50       |      0.000462     |
+-----------------+------------------+----------------+----------------+-------------------+---------------------+-------------------+


## 1.6 Dynamic coefficients

To display the stiffness and damping coefficients for all analyzed speeds in table format, use:

In [6]:
plainjournal.show_coefficients_comparison()


                                             DYNAMIC COEFFICIENTS COMPARISON TABLE                                              
+-----------------+------------+------------+-------------+------------+-------------+-------------+-------------+-------------+
| Frequency [RPM] | kxx [N/m]  | kxy [N/m]  |  kyx [N/m]  | kyy [N/m]  | cxx [N*s/m] | cxy [N*s/m] | cyx [N*s/m] | cyy [N*s/m] |
+-----------------+------------+------------+-------------+------------+-------------+-------------+-------------+-------------+
|      900.0      | 8.8016e+08 | 1.7801e+08 | -1.8695e+09 | 1.8799e+09 |  1.0487e+07 | -9.7290e+06 | -9.7290e+06 |  3.7247e+07 |
|      1200.0     | 9.3497e+08 | 3.3469e+08 | -1.9003e+09 | 1.6221e+09 |  9.8409e+06 | -8.0807e+06 | -8.0807e+06 |  2.8614e+07 |
+-----------------+------------+------------+-------------+------------+-------------+-------------+-------------+-------------+


The `coefficients` method interpolates the coefficient tables at any speed, returning the stiffness tuple `(kxx, kxy, kyx, kyy)` and the damping tuple `(cxx, cxy, cyx, cyy)`:

In [7]:
stiffness, damping = plainjournal.coefficients(Q_(1000, "RPM"))
stiffness

(2460330315.7692947,
 4695215138.429182,
 -2757640857.6827393,
 -5551565332.833534)

## 1.7 Fixed-geometry configurations

`PlainJournal` covers the plain cylindrical bore. The other classic fixed-geometry configurations have dedicated classes built on the same engine:

| Class | Configuration |
| --- | --- |
| `PartialArcBearing` | Single partial-arc pad |
| `EllipticalBearing` | Two-lobe elliptical (lemon) bore |
| `OffsetHalvesBearing` | Offset halves |
| `MultiLobeBearing` | Three or more lobes with per-lobe preload |
| `PressureDamBearing` | Stepped pocket (dam) in selected pads |

They accept the full parameter surface of `FluidFilmBearing` — thermal model, operating condition, turbulence, mesh — and arbitrary pad layouts (pockets, tapers, per-pad preload and offset) can be described directly with `FixedGeometryBearing`. For example, an elliptical bearing with preload 0.5:

In [8]:
lemon = rs.EllipticalBearing(
    n=0,
    speed=Q_([3000], "RPM"),
    pad_arc=Q_(150, "deg"),
    preload=0.5,
    journal_diameter=0.2,
    radial_clearance=150e-6,
    pad_thickness=0.05,
    pad_axial_length=[0.16, 0.16],
    lubricant="ISOVG32",
    oil_supply_temperature=Q_(40, "degC"),
    oil_flow_v=Q_(30, "l/min"),
    weight=45e3,  # Rotor weight carried by the bearing
    thermal_type="adiabatic",
)
lemon.show_results()


                                                      FLUID FILM BEARING RESULTS                                                      
+-----------------+------------------+----------------+----------------+-------------------+---------------------+-------------------+
| Frequency [RPM] | Eccentricity [-] | Attitude [deg] | Power loss [W] | Max pressure [Pa] | Max temperature [K] | Side flow [m^3/s] |
+-----------------+------------------+----------------+----------------+-------------------+---------------------+-------------------+
|      3000.0     |      0.8692      |      73.0      |   1.008e+04    |     4.383e+06     |        335.94       |     0.0004092     |
+-----------------+------------------+----------------+----------------+-------------------+---------------------+-------------------+


And a pressure-dam bearing with the dam pocket in the top (unloaded) pad:

In [9]:
dam = rs.PressureDamBearing(
    n=0,
    speed=Q_([3000], "RPM"),
    pad_arc=Q_(150, "deg"),
    dam_arc=Q_(90, "deg"),  # Pocket arc length from the pad leading edge
    dam_axial_length=0.1,  # Pocket axial length
    dam_depth=250e-6,  # Pocket depth
    journal_diameter=0.2,
    radial_clearance=150e-6,
    pad_thickness=0.05,
    pad_axial_length=[0.16, 0.16],
    lubricant="ISOVG32",
    oil_supply_temperature=Q_(40, "degC"),
    oil_flow_v=Q_(30, "l/min"),
    weight=45e3,
    thermal_type="adiabatic",
)
dam.plot_pressure_2d()

## 1.8 Final remarks

To perform quick analyses of short bearings, ROSS provides the `CylindricalBearing` class, which models the fluid film using a closed-form solution of the Reynolds equation:

In [10]:
cylindrical = rs.CylindricalBearing(
    n=0,
    speed=Q_([1500, 2000], "RPM"),
    weight=525,
    bearing_length=Q_(30, "mm"),
    journal_diameter=Q_(100, "mm"),
    radial_clearance=Q_(0.1, "mm"),
    oil_viscosity=0.1,
)

To display the value of a specific dynamic coefficient (e.g. `kxx`) for all the analyzed speeds, use:

In [11]:
cylindrical.kxx

[12807959.577408731, 13005276.627694618]

# Section 2: TiltingPad

This section shows how to simulate tilting-pad journal bearings and compute their dynamic coefficients.

Tilting-pad bearings differ from fixed-geometry bearings because each pad can rotate around its pivot, which practically eliminates the cross-coupled stiffness responsible for oil-whirl instability. For every speed the engine solves the pad tilt angles and the journal position together with the film fields, then condenses the pad degrees of freedom into the eight synchronous stiffness and damping coefficients.

Three thermal modeling levels are available through `thermal_type`:

- `None`: isoviscous film (fastest; no temperature field)

- `"adiabatic"`: only the oil-film temperature is computed

- `"full"` (default): adds heat conduction into the pads

## 2.1 Adiabatic example of application

To run a test case using the adiabatic thermal model, use:

In [12]:
tilting_pad_adiabatic = rs.TiltingPad(
    n=1,  # Nodal location of the bearing in the FE model of the rotor
    speed=Q_([3000, 5000], "RPM"),  # Journal rotational speed
    equilibrium_type="match_load",  # Solve the journal position for the load
    fxs_load=884.05,  # External load applied to the shaft, horizontal direction
    fys_load=-2670.4,  # External load applied to the shaft, vertical direction
    journal_diameter=101.6e-3,  # Journal diameter
    radial_clearance=74.9e-6,  # Radial clearance
    pad_thickness=12.7e-3,  # Pad thickness
    pivot_angle=Q_([18, 90, 162, 234, 306], "deg"),  # Pivot angular positions
    pad_arc=Q_([60] * 5, "deg"),  # Angular extent of each pad
    pad_axial_length=[50.8e-3] * 5,  # Axial length of each pad
    preload=[0.5] * 5,  # Preload factor for each pad
    offset=[0.5] * 5,  # Pivot offset factor for each pad
    lubricant="ISOVG32",  # Lubricant type
    oil_supply_temperature=Q_(40, "degC"),  # Oil supply temperature
    oil_flow_v=Q_(10, "l/min"),  # Supplied oil flow
    thermal_type="adiabatic",  # Only the oil-film temperature is computed
)

## 2.2 Equilibrium calculation options

The `equilibrium_type` parameter selects how the journal position is determined:

- `"match_load"`: the journal position is solved so that the film forces balance the applied `load` (this replaces the previous `"determine_eccentricity"` option).

- `"match_eccentricity"` (default, the historical behavior): the journal is held at the position given by `eccentricity` and `attitude_angle` (or directly by `xj`/`yj`, as fractions of the radial clearance), and only the pad tilt equilibrium is solved. The resulting film forces are reported in the results and in general do not match the applied load.

**Holding a prescribed eccentricity (`match_eccentricity`):**

In [13]:
tilting_pad_match = rs.TiltingPad(
    n=1,
    speed=Q_([3000], "RPM"),
    equilibrium_type="match_eccentricity",
    eccentricity=0.35,  # Prescribed eccentricity ratio
    attitude_angle=Q_(287.5, "deg"),  # Prescribed attitude angle
    journal_diameter=101.6e-3,
    radial_clearance=74.9e-6,
    pad_thickness=12.7e-3,
    pivot_angle=Q_([18, 90, 162, 234, 306], "deg"),
    pad_arc=Q_([60] * 5, "deg"),
    pad_axial_length=[50.8e-3] * 5,
    preload=[0.5] * 5,
    offset=[0.5] * 5,
    lubricant="ISOVG32",
    oil_supply_temperature=Q_(40, "degC"),
    oil_flow_v=Q_(10, "l/min"),
    thermal_type="adiabatic",
)
tilting_pad_match.show_results()


                                                      FLUID FILM BEARING RESULTS                                                      
+-----------------+------------------+----------------+----------------+-------------------+---------------------+-------------------+
| Frequency [RPM] | Eccentricity [-] | Attitude [deg] | Power loss [W] | Max pressure [Pa] | Max temperature [K] | Side flow [m^3/s] |
+-----------------+------------------+----------------+----------------+-------------------+---------------------+-------------------+
|      3000.0     |      0.3500      |      17.5      |      1060      |     1.882e+06     |        329.49       |     4.032e-05     |
+-----------------+------------------+----------------+----------------+-------------------+---------------------+-------------------+


Note that the eccentricity reported for `tilting_pad_match` is exactly the prescribed 0.35, while the load-matched bearing of Section 2.1 converged to the eccentricity that balances the applied load.

## 2.3 Execution time

To display the total execution time of the thermo-hydrodynamic analysis, use:

In [14]:
tilting_pad_adiabatic.show_execution_time()

Execution time: 829.684623 seconds


## 2.4 Pressure and temperature distributions

The `plot_results` method generates the standard set of field plots for all pads. The `freq_index` parameter selects which solved speed to visualize:

- `freq_index=0` → first speed (3000 RPM)
- `freq_index=1` → second speed (5000 RPM)

In [15]:
tilting_pad_adiabatic.plot_results(show_plots=True, freq_index=1);

## 2.5 Single-pad fields

The 3D surface plots accept a `pad_index` argument to isolate one pad. Pads are numbered from 0 in the order of `pivot_angle`; for this load direction the most loaded pads are the bottom ones. To display the pressure field of pad 3 (pivot at 234°):

In [16]:
tilting_pad_adiabatic.plot_pressure_3d(freq_index=0, pad_index=3)

And its film temperature field:

In [17]:
tilting_pad_adiabatic.plot_film_temperature_3d(freq_index=0, pad_index=3)

## 2.6 Film thickness

To display the film thickness along the mid-plane of all pads, use:

In [18]:
tilting_pad_adiabatic.plot_film_thickness_2d()

## 2.7 Dynamic coefficients

To display the stiffness and damping coefficients for each rotational speed, use:

In [19]:
tilting_pad_adiabatic.show_coefficients_comparison()


                                              DYNAMIC COEFFICIENTS COMPARISON TABLE                                              
+-----------------+------------+-------------+-------------+------------+-------------+-------------+-------------+-------------+
| Frequency [RPM] | kxx [N/m]  |  kxy [N/m]  |  kyx [N/m]  | kyy [N/m]  | cxx [N*s/m] | cxy [N*s/m] | cyx [N*s/m] | cyy [N*s/m] |
+-----------------+------------+-------------+-------------+------------+-------------+-------------+-------------+-------------+
|      3000.0     | 8.4475e+07 | -2.2134e+07 | -2.2081e+07 | 1.1700e+08 |  2.5497e+05 | -3.5291e+04 | -3.5398e+04 |  3.1364e+05 |
|      5000.0     | 1.0430e+08 | -1.4855e+07 | -1.4707e+07 | 1.2898e+08 |  2.0665e+05 | -1.4648e+04 | -1.4822e+04 |  2.3377e+05 |
+-----------------+------------+-------------+-------------+------------+-------------+-------------+-------------+-------------+


## 2.8 Results summary

To display in table format the converged solution for each speed analyzed, use:

In [20]:
tilting_pad_adiabatic.show_results()


                                                      FLUID FILM BEARING RESULTS                                                      
+-----------------+------------------+----------------+----------------+-------------------+---------------------+-------------------+
| Frequency [RPM] | Eccentricity [-] | Attitude [deg] | Power loss [W] | Max pressure [Pa] | Max temperature [K] | Side flow [m^3/s] |
+-----------------+------------------+----------------+----------------+-------------------+---------------------+-------------------+
|      3000.0     |      0.4140      |      17.8      |      1075      |     2.335e+06     |        331.56       |      3.98e-05     |
|      5000.0     |      0.3190      |      18.4      |      2587      |     2.504e+06     |        335.76       |     6.876e-05     |
+-----------------+------------------+----------------+----------------+-------------------+---------------------+-------------------+


## 2.9 Full thermal example of application

To include heat conduction from the film into the pads, keep the default `thermal_type="full"` and describe the pad material and its cooling:

In [21]:
tilting_pad_full = rs.TiltingPad(
    n=1,
    speed=Q_([3000], "RPM"),
    equilibrium_type="match_load",
    fxs_load=884.05,
    fys_load=-2670.4,
    journal_diameter=101.6e-3,
    radial_clearance=74.9e-6,
    pad_thickness=12.7e-3,
    pivot_angle=Q_([18, 90, 162, 234, 306], "deg"),
    pad_arc=Q_([60] * 5, "deg"),
    pad_axial_length=[50.8e-3] * 5,
    preload=[0.5] * 5,
    offset=[0.5] * 5,
    lubricant="ISOVG32",
    oil_supply_temperature=Q_(40, "degC"),
    oil_flow_v=Q_(10, "l/min"),
    thermal_type="full",  # Film energy equation + pad conduction
    total_ey_pad=20,  # Radial pad elements
    pad_conductivity=45.0,  # Pad thermal conductivity [W/(m·K)]
    edges_convection=2000.0,  # Pad edge convection coefficient [W/(m²·K)]
    hot_oil_lambda=0.8,  # Hot-oil carryover factor of the groove mixing model
)
tilting_pad_full.show_results()


                                                      FLUID FILM BEARING RESULTS                                                      
+-----------------+------------------+----------------+----------------+-------------------+---------------------+-------------------+
| Frequency [RPM] | Eccentricity [-] | Attitude [deg] | Power loss [W] | Max pressure [Pa] | Max temperature [K] | Side flow [m^3/s] |
+-----------------+------------------+----------------+----------------+-------------------+---------------------+-------------------+
|      3000.0     |      0.4051      |      16.7      |      1085      |     2.337e+06     |        328.90       |     3.823e-05     |
+-----------------+------------------+----------------+----------------+-------------------+---------------------+-------------------+


All plotting commands from the adiabatic example remain valid; the film temperature now reflects the heat conducted into the pads:

In [22]:
tilting_pad_full.plot_temperature_2d()

The solid pad conduction field can also be drawn as real pad geometry with `plot_pad_temperature_3d`, the through-pad counterpart of `plot_film_temperature_3d`. Each pad is placed at its true angular position and colored by the solid pad temperature, resolved through the pad thickness from the babbitt surface (dashed red outline) out to the pad back.

The two views are complementary and resolve different dimensions: `plot_film_temperature_3d` draws the oil film field over circumferential × axial, while `plot_pad_temperature_3d` draws the solid over circumferential × radial. The solver does not resolve the solid temperature along the bearing axis, so the axial extrusion is geometric — both axial faces of a pad carry the same field. The plot is only available with `thermal_type="full"`, since the adiabatic model computes no solid pad field:

In [23]:
tilting_pad_full.plot_pad_temperature_3d(length_units="mm")

## 2.10 Pivot flexibility and other engine capabilities

The rewrite exposes more of the engine's tilting-pad capabilities through keyword arguments (see `FluidFilmBearing` for the full list):

- **Pivot flexibility** — `deform_type="pad_pivot_mechanical"` adds the pivot compliance to the pad equilibrium. `pivot_type` selects a Hertzian contact model (`"ball_in_socket"`, `"button"` or `"rocker_back"`, sized by `house_diameter` and `pivot_diameter`) or `"user_specified_stiffness"` with `pivot_stiffness`.

- **Lubrication variants** — `bearing_type="inlet_groove_tilting_pad"` (leading-edge groove) or `"spray_bar_tilting_pad"`; `operating_type` selects flooded, starved or high-ambient-pressure operation.

- **Parallel solve** — `num_processes` distributes the entries of `frequency` over worker processes.

- **Serialization** — `save()` stores the solved coefficient table, which reloads as a plain `BearingElement` without re-solving.

For example, adding a flexible pivot softens the bearing noticeably:

In [24]:
tilting_pad_flex_pivot = rs.TiltingPad(
    n=1,
    speed=Q_([3000], "RPM"),
    equilibrium_type="match_load",
    fxs_load=884.05,
    fys_load=-2670.4,
    journal_diameter=101.6e-3,
    radial_clearance=74.9e-6,
    pad_thickness=12.7e-3,
    pivot_angle=Q_([18, 90, 162, 234, 306], "deg"),
    pad_arc=Q_([60] * 5, "deg"),
    pad_axial_length=[50.8e-3] * 5,
    preload=[0.5] * 5,
    offset=[0.5] * 5,
    lubricant="ISOVG32",
    oil_supply_temperature=Q_(40, "degC"),
    oil_flow_v=Q_(10, "l/min"),
    thermal_type="adiabatic",
    deform_type="pad_pivot_mechanical",  # Include pivot compliance
    pivot_type="user_specified_stiffness",
    pivot_stiffness=5e8,  # Pivot stiffness [N/m]
)
tilting_pad_flex_pivot.show_coefficients_comparison()


                                              DYNAMIC COEFFICIENTS COMPARISON TABLE                                              
+-----------------+------------+-------------+-------------+------------+-------------+-------------+-------------+-------------+
| Frequency [RPM] | kxx [N/m]  |  kxy [N/m]  |  kyx [N/m]  | kyy [N/m]  | cxx [N*s/m] | cxy [N*s/m] | cyx [N*s/m] | cyy [N*s/m] |
+-----------------+------------+-------------+-------------+------------+-------------+-------------+-------------+-------------+
|      3000.0     | 7.4852e+07 | -1.6053e+07 | -1.6005e+07 | 1.0194e+08 |  1.9401e+05 | -9.5741e+03 | -9.6883e+03 |  2.2155e+05 |
+-----------------+------------+-------------+-------------+------------+-------------+-------------+-------------+-------------+


# Section 3: ThrustPad

This tutorial demonstrates how to use the `ThrustPad` class from ROSS to simulate the thermo-hydrodynamic behavior of tilting-pad thrust bearings and compute their dynamic coefficients for different operating conditions.

Thrust bearings are designed to support axial (thrust) loads and are commonly found in rotating machinery such as turbines, compressors, and pumps. The tilting-pad design allows each pad to tilt around a pivot point, creating a converging oil film that generates the hydrodynamic pressure needed to support the load.

The `ThrustPad` class implements a **Thermo-Hydro-Dynamic (THD)** model that solves the coupled Reynolds (pressure) and energy (temperature) equations for each pad. The main outputs are:

- Pressure and temperature distributions across each pad

- Film thickness at the pivot point

- Axial stiffness coefficient `kzz` [N/m]

- Axial damping coefficient `czz` [N·s/m]

There are two modes for determining the pad equilibrium position:

- **`calculate`**: The solver finds the equilibrium film thickness and inclination angles simultaneously by minimizing residual forces and moments.

- **`imposed`**: The film thickness at the pivot is fixed by the user; only the inclination angles are optimized.

## 3.1 Calculate mode

In the `calculate` mode, the equilibrium film thickness is determined automatically by the solver together with the radial and circumferential inclination angles. Initial estimates must be provided as starting points for the optimization.

The example below represents a large industrial thrust bearing (e.g., in a hydraulic turbine) with 12 pads, operating at 90 RPM under an axial load of 13.32 MN:

In [25]:
from ross.bearings.thrust_pad import ThrustPad
from ross.units import Q_

import plotly.io as pio

pio.renderers.default = "notebook"

bearing_calculate = ThrustPad(
    n=1,  # Node in the FE model of the rotor
    pad_inner_radius=Q_(1150, "mm"),  # Inner radius of the pad
    pad_outer_radius=Q_(1725, "mm"),  # Outer radius of the pad
    pad_pivot_radius=Q_(1442.5, "mm"),  # Radius of the pivot point
    pad_arc=Q_(26, "deg"),  # Arc length of each pad
    pivot_angle=Q_(15, "deg"),  # Angular position of the pivot
    oil_supply_temperature=Q_(40, "degC"),  # Oil inlet temperature
    lubricant="ISOVG68",  # Lubricant type
    n_pads=12,  # Number of pads
    n_theta=10,  # Mesh elements in circumferential dir.
    n_radial=10,  # Mesh elements in radial dir.
    speed=Q_([90], "RPM"),  # Rotor speed
    equilibrium_position_mode="calculate",  # Auto-calculate film thickness
    axial_load=13.320e6,  # Total axial load [N]
    radial_inclination_angle=Q_(-2.75e-04, "rad"),  # Initial radial inclination angle
    circumferential_inclination_angle=Q_(
        -1.70e-05, "rad"
    ),  # Initial circumferential inclination
    initial_film_thickness=Q_(0.2, "mm"),  # Initial film thickness estimate
)

The `ThrustPad` class automatically runs the full THD analysis during instantiation. The inner loop solves the Reynolds and energy equations iteratively until the viscosity field converges, while the outer loop finds the equilibrium position using Nelder-Mead optimization.

## 3.2 Optimization convergence

To display — in both table and graph formats — the evolution of the residual force/moment during the optimization process, use:

In [26]:
bearing_calculate.show_optimization_convergence(show_plots=True)


           OPTIMIZATION CONVERGENCE - 90.0 RPM           
+---------------------------+---------------------------+
|         Iteration         |        Residual [N]       |
+---------------------------+---------------------------+
|             1             |       378947.112688       |
|             2             |        27724.023669       |
|             3             |        4753.901941        |
|             4             |        2267.382187        |
|             5             |         381.146245        |
|             6             |         25.796494         |
|             7             |          6.502821         |
|             8             |          0.143314         |
|             9             |          0.162634         |
|             10            |          0.113231         |
|             11            |          0.084976         |
+---------------------------+---------------------------+


Each row in the table corresponds to one iteration of the outer convergence loop. The residual represents the net force/moment imbalance [N] at the current pad equilibrium estimate. The optimization converges when this residual falls below the `tolerance_force_moment` threshold (default: 0.1 N).

## 3.3 Execution time

To display the total wall-clock time spent during the analysis, use:

In [27]:
bearing_calculate.show_execution_time()

Execution time: 1.269173 seconds


## 3.4 Pressure and temperature distributions

The `plot_results` method generates both 3D surface plots and 2D contour plots for the pressure and temperature fields across the bearing pad.

The `freq_index` parameter selects which operating speed to visualize. Since a single speed was defined (90 RPM), `freq_index=0` corresponds to that speed:

In [28]:
figs = bearing_calculate.plot_results(show_plots=True, freq_index=0)

The method returns a dictionary with four Plotly figure objects:

- `'pressure_3D'`: 3D surface plot of the pressure field [Pa]

- `'temperature_3D'`: 3D surface plot of the temperature field [°C]

- `'pressure_2D'`: 2D contour plot of the pressure field [Pa]

- `'temperature_2D'`: 2D contour plot of the temperature field [°C]

The coordinates are transformed from polar (r, θ) to Cartesian (x, y) for visualization. Atmospheric pressure is enforced at the pad edges as a boundary condition, so the pressure field rises from zero at the inlet/outlet edges.

## 3.5 Dynamic coefficients

To display in table format the axial stiffness `kzz` and damping `czz` coefficients for all analyzed speeds, use:

In [29]:
bearing_calculate.show_coefficients_comparison()


                        DYNAMIC COEFFICIENTS COMPARISON TABLE                        
+---------------------------+---------------------------+---------------------------+
|      Frequency [RPM]      |         kzz [N/m]         |        czz [N*s/m]        |
+---------------------------+---------------------------+---------------------------+
|            90.0           |         3.1763e+11        |         1.0806e+10        |
+---------------------------+---------------------------+---------------------------+


The dynamic coefficients are computed using the perturbation method: small virtual displacements and velocities are applied to the axial position, and the resulting force differences are used to extract `kzz` and `czz`.

The coefficients can also be accessed directly as arrays:

In [30]:
print("kzz [N/m]:", bearing_calculate.kzz)
print("czz [N·s/m]:", bearing_calculate.czz)

kzz [N/m]: [317634346752.77313]
czz [N·s/m]: [10805979814.239801]


## 3.6 Show results

To display a comprehensive summary table with operating conditions, field results, load information, and dynamic coefficients for each analyzed speed, use:

In [31]:
bearing_calculate.show_results()


                          THRUST BEARING RESULTS - 90.0 RPM                          
+---------------------------+---------------------------+---------------------------+
|         Parameter         |           Value           |            Unit           |
+---------------------------+---------------------------+---------------------------+
|      Operating Speed      |            90.0           |            RPM            |
|      Equilibrium Mode     |         calculate         |             -             |
|      Maximum Pressure     |         6.9570e+06        |             Pa            |
|    Maximum Temperature    |            70.4           |             °C            |
|   Maximum Film Thickness  |         2.0652e-04        |             m             |
|   Minimum Film Thickness  |         8.1598e-05        |             m             |
|    Pivot Film Thickness   |         1.3150e-04        |             m             |
|         Axial Load        |         1.3320e+07     

The results table includes:

| Parameter | Description |
|-----------|-------------|
| Operating Speed | Rotational speed [RPM] |
| Equilibrium Mode | `calculate` or `imposed` |
| Maximum Pressure | Peak pressure in the film [Pa] |
| Maximum Temperature | Peak temperature in the film [°C] |
| Maximum Film Thickness | Max. oil film thickness [m] |
| Minimum Film Thickness | Min. oil film thickness [m] |
| Pivot Film Thickness | Film thickness at pivot point [m] |
| Axial Load | Total axial load [N] |
| kzz | Axial stiffness coefficient [N/m] |
| czz | Axial damping coefficient [N·s/m] |

## 3.7 Imposed mode

In the `imposed` mode, the film thickness at the pivot point is fixed by the user. The solver then finds only the radial and circumferential inclination angles that satisfy moment equilibrium for that prescribed film thickness. The axial load is an output of the calculation in this mode.

This mode is useful when the film thickness is known from measurements or a reference design, and one wants to determine the resulting load capacity and dynamic coefficients.

The example below uses the same bearing geometry operating at two speeds (90 RPM and 120 RPM) with a prescribed film thickness:

In [32]:
from ross.bearings.thrust_pad import ThrustPad
from ross.units import Q_
import numpy as np

bearing_imposed = ThrustPad(
    n=1,
    pad_inner_radius=Q_(1150, "mm"),
    pad_outer_radius=Q_(1725, "mm"),
    pad_pivot_radius=Q_(1442.5, "mm"),
    pad_arc=Q_(26, "deg"),
    pivot_angle=Q_(15, "deg"),
    oil_supply_temperature=Q_(40, "degC"),
    lubricant="ISOVG68",
    n_pads=12,
    n_theta=10,
    n_radial=10,
    speed=Q_([90, 120], "RPM"),  # Two operating speeds
    equilibrium_position_mode="imposed",  # Fixed film thickness
    axial_load=np.array([13.320e6, 13.320e6]),  # Axial load for each speed [N]
    radial_inclination_angle=Q_(-2.75e-04, "rad"),
    circumferential_inclination_angle=Q_(-1.70e-05, "rad"),
    initial_film_thickness=Q_(0.2, "mm"),  # Film thickness is fixed at this value
)

Optimization terminated successfully.
         Current function value: 0.079362
         Iterations: 75
         Function evaluations: 136
Optimization terminated successfully.
         Current function value: 0.159000
         Iterations: 56
         Function evaluations: 97


Optimization terminated successfully.
         Current function value: 0.122354
         Iterations: 39
         Function evaluations: 77


Optimization terminated successfully.
         Current function value: 0.076233
         Iterations: 33
         Function evaluations: 62
Optimization terminated successfully.
         Current function value: 0.073585
         Iterations: 28
         Function evaluations: 56
Optimization terminated successfully.
         Current function value: 0.098058
         Iterations: 25
         Function evaluations: 52


Optimization terminated successfully.
         Current function value: 0.120753
         Iterations: 48
         Function evaluations: 87


Optimization terminated successfully.
         Current function value: 0.178821
         Iterations: 36
         Function evaluations: 68
Optimization terminated successfully.
         Current function value: 0.096513
         Iterations: 33
         Function evaluations: 63
Optimization terminated successfully.
         Current function value: 0.275488
         Iterations: 25
         Function evaluations: 50
Optimization terminated successfully.
         Current function value: 0.077632
         Iterations: 26
         Function evaluations: 53


## 3.8 Optimization convergence

The convergence behavior in `imposed` mode is different from `calculate` mode: since the film thickness is fixed, the solver only needs to find two inclination angles. This generally leads to faster convergence.

In [33]:
bearing_imposed.show_optimization_convergence(show_plots=True)


           OPTIMIZATION CONVERGENCE - 90.0 RPM           
+---------------------------+---------------------------+
|         Iteration         |        Residual [N]       |
+---------------------------+---------------------------+
|             1             |        4391.077587        |
|             2             |         277.778587        |
|             3             |         17.314713         |
|             4             |          1.222665         |
|             5             |          0.094196         |
+---------------------------+---------------------------+



           OPTIMIZATION CONVERGENCE - 120.0 RPM          
+---------------------------+---------------------------+
|         Iteration         |        Residual [N]       |
+---------------------------+---------------------------+
|             1             |        1762.804336        |
|             2             |         131.775332        |
|             3             |         10.385081         |
|             4             |          0.928356         |
|             5             |          0.275488         |
|             6             |          0.077632         |
+---------------------------+---------------------------+


When multiple speeds are defined, the convergence history for each speed is displayed separately.

## 3.9 Pressure and temperature distributions

To visualize the fields for the second speed (120 RPM), pass `freq_index=1`:

In [34]:
figs = bearing_imposed.plot_results(show_plots=True, freq_index=1)

## 3.10 Dynamic coefficients comparison

When multiple speeds are defined, `show_coefficients_comparison` displays one row per speed:

In [35]:
bearing_imposed.show_coefficients_comparison()


                        DYNAMIC COEFFICIENTS COMPARISON TABLE                        
+---------------------------+---------------------------+---------------------------+
|      Frequency [RPM]      |         kzz [N/m]         |        czz [N*s/m]        |
+---------------------------+---------------------------+---------------------------+
|            90.0           |         9.2871e+10        |         3.7426e+09        |
|           120.0           |         1.2325e+11        |         3.5372e+09        |
+---------------------------+---------------------------+---------------------------+


## 3.11 Full results summary

In [36]:
bearing_imposed.show_results()


                          THRUST BEARING RESULTS - 90.0 RPM                          
+---------------------------+---------------------------+---------------------------+
|         Parameter         |           Value           |            Unit           |
+---------------------------+---------------------------+---------------------------+
|      Operating Speed      |            90.0           |            RPM            |
|      Equilibrium Mode     |          imposed          |             -             |
|      Maximum Pressure     |         3.1525e+06        |             Pa            |
|    Maximum Temperature    |            56.0           |             °C            |
|   Maximum Film Thickness  |         3.0028e-04        |             m             |
|   Minimum Film Thickness  |         1.3753e-04        |             m             |
|    Pivot Film Thickness   |         2.0000e-04        |             m             |
|         Axial Load        |         1.1928e+07     

## 3.12 Using the example function

ROSS provides the `thrust_pad_example` convenience function that returns a pre-configured `ThrustPad` instance. This is useful for quick tests and verification:

In [37]:
from ross.bearings.thrust_pad import thrust_pad_example

bearing = thrust_pad_example()
bearing.show_results()


                          THRUST BEARING RESULTS - 90.0 RPM                          
+---------------------------+---------------------------+---------------------------+
|         Parameter         |           Value           |            Unit           |
+---------------------------+---------------------------+---------------------------+
|      Operating Speed      |            90.0           |            RPM            |
|      Equilibrium Mode     |         calculate         |             -             |
|      Maximum Pressure     |         6.9570e+06        |             Pa            |
|    Maximum Temperature    |            70.4           |             °C            |
|   Maximum Film Thickness  |         2.0652e-04        |             m             |
|   Minimum Film Thickness  |         8.1598e-05        |             m             |
|    Pivot Film Thickness   |         1.3150e-04        |             m             |
|         Axial Load        |         1.3320e+07     

The example bearing has the following configuration:

| Parameter | Value |
|-----------|-------|
| Number of pads | 12 |
| Pad inner radius | 1150 mm |
| Pad outer radius | 1725 mm |
| Pad pivot radius | 1442.5 mm |
| Pad arc length | 26° |
| Angular pivot position | 15° |
| Lubricant | ISOVG68 |
| Oil supply temperature | 40 °C |
| Operating speed | 90 RPM |
| Equilibrium mode | `calculate` |
| Axial load | 13.32 MN |
| Initial film thickness | 0.2 mm |

## 3.13 Integrating with a rotor model

The `ThrustPad` class inherits from `BearingElement`, which means it can be directly inserted into a `Rotor` assembly like any other bearing element. The computed `kzz` and `czz` coefficients are automatically passed to the rotor's global stiffness and damping matrices.

The example below builds a simple rotor with a thrust bearing at node 1:

In [38]:
import ross as rs
from ross.bearings.thrust_pad import thrust_pad_example

# Build a simple rotor
steel = rs.Material(name="Steel", rho=7810, E=211e9, G_s=81.2e9)
shaft = [rs.ShaftElement(L=0.25, idl=0, odl=0.05, material=steel) for _ in range(4)]
disk = rs.DiskElement.from_geometry(n=2, material=steel, width=0.07, i_d=0.05, o_d=0.28)

# Radial bearings at the shaft ends
brg0 = rs.BearingElement(n=0, kxx=1e8, cxx=0)
brg4 = rs.BearingElement(n=4, kxx=1e8, cxx=0)

# Thrust bearing at node 1 (uses kzz/czz from the THD analysis)
thrust = thrust_pad_example()  # n=1 is already set in the example

rotor = rs.Rotor(
    shaft_elements=shaft,
    disk_elements=[disk],
    bearing_elements=[brg0, brg4, thrust],
)

# Run modal analysis
modal = rotor.run_modal(speed=0)
print("Natural frequencies [Hz]:", modal.wn[:4] / (2 * 3.14159))

Natural frequencies [Hz]: [ 43.83201484  43.83201484 265.60781314 265.60781314]


## 3.14 Available lubricants <a id="sec-3-14-lubricants"></a>

All four THD bearing classes in this tutorial — `PlainJournal`, `TiltingPad`, `ThrustPad`, and `SqueezeFilmDamper` — share the same lubricant interface. Three standard ISO viscosity grade lubricants are available out of the box and can be specified by name using the `lubricant` parameter:

| Lubricant string | ISO grade | Typical viscosity at 40 °C |
|-----------------|-----------|---------------------------|
| `'ISOVG32'` | ISO VG 32 | ~32 mm²/s |
| `'ISOVG46'` | ISO VG 46 | ~46 mm²/s |
| `'ISOVG68'` | ISO VG 68 | ~68 mm²/s |

All four classes also accept a **custom lubricant** by passing a dictionary with the required thermophysical properties to the `lubricant` parameter:

In [39]:
from ross.bearings.lubricants import lubricants_dict

# Inspect the properties of ISOVG46
relevant_keys = [
    "liquid_density",
    "liquid_thermal_conductivity",
    "liquid_specific_heat",
    "temperature1",
    "liquid_viscosity1",
    "temperature2",
    "liquid_viscosity2",
]
props = lubricants_dict["ISOVG46"]
for key in relevant_keys:
    print(f"  {key}: {props[key]:.6g}")

  liquid_density: 862.9
  liquid_thermal_conductivity: 0.15
  liquid_specific_heat: 1950
  temperature1: 313.15
  liquid_viscosity1: 0.0396934
  temperature2: 373.15
  liquid_viscosity2: 0.00607482


To use a custom lubricant with any of the four bearing classes, pass a dictionary with the same keys:

In [40]:
custom_lubricant = {
    "liquid_density": 860,  # [kg/m³]
    "liquid_thermal_conductivity": 0.13,  # [W/(m·K)]
    "liquid_specific_heat": 2000,  # [J/(kg·K)]
    "temperature1": 313.15,  # [K] — reference temperature 1
    "liquid_viscosity1": 0.040,  # [Pa·s] — viscosity at temperature 1
    "temperature2": 373.15,  # [K] — reference temperature 2
    "liquid_viscosity2": 0.010,  # [Pa·s] — viscosity at temperature 2
}

bearing_custom = ThrustPad(
    n=1,
    pad_inner_radius=Q_(1150, "mm"),
    pad_outer_radius=Q_(1725, "mm"),
    pad_pivot_radius=Q_(1442.5, "mm"),
    pad_arc=Q_(26, "deg"),
    pivot_angle=Q_(15, "deg"),
    oil_supply_temperature=Q_(40, "degC"),
    lubricant=custom_lubricant,  # Pass the dict instead of a string
    n_pads=12,
    n_theta=10,
    n_radial=10,
    speed=Q_([90], "RPM"),
    equilibrium_position_mode="calculate",
    axial_load=13.320e6,
    radial_inclination_angle=Q_(-2.75e-04, "rad"),
    circumferential_inclination_angle=Q_(-1.70e-05, "rad"),
    initial_film_thickness=Q_(0.2, "mm"),
)

bearing_custom.show_results()


                          THRUST BEARING RESULTS - 90.0 RPM                          
+---------------------------+---------------------------+---------------------------+
|         Parameter         |           Value           |            Unit           |
+---------------------------+---------------------------+---------------------------+
|      Operating Speed      |            90.0           |            RPM            |
|      Equilibrium Mode     |         calculate         |             -             |
|      Maximum Pressure     |         6.9670e+06        |             Pa            |
|    Maximum Temperature    |            72.4           |             °C            |
|   Maximum Film Thickness  |         1.7119e-04        |             m             |
|   Minimum Film Thickness  |         7.3458e-05        |             m             |
|    Pivot Film Thickness   |         1.1172e-04        |             m             |
|         Axial Load        |         1.3320e+07     

# Section 4: SqueezeFilmDamper

This tutorial demonstrates how to use the `SqueezeFilmDamper` class from ROSS to compute the dynamic coefficients of squeeze film dampers (SFDs) using classical short-bearing theory.

Squeeze film dampers are passive damping devices widely used in rotating machinery to suppress vibrations and improve rotordynamic stability. They operate by generating a hydrodynamic pressure in the thin oil film between a non-rotating sleeve and the journal, which is driven by the orbital motion of the rotor.

The `SqueezeFilmDamper` class implements an **analytical short-bearing model** based on closed-form solutions to the Reynolds equation. The main outputs for each operating speed are:

- Direct damping coefficient `cxx` [N·s/m]

- Direct stiffness coefficient `kxx` [N/m] (due to oil film inertia/cavitation effects)

- Maximum pressure in the oil film `p_max` [Pa]

- Pressure angle `theta` [rad]

Three bearing geometries are supported:

| `geometry` string | Description |
|-------------------|-------------|
| `'groove'` | Central groove, open ends (no end seals) |
| `'end_seals'` | Closed ends (end seals), no groove |
| `'groove-end_seals'` | Central groove **and** end seals |

Cavitation behavior is controlled by the `cavitation` parameter (`True` or `False`).

## 4.1 Groove geometry (open ends)

The groove geometry assumes a central circumferential groove that feeds oil into the damper and two open ends through which oil can escape freely. This is the most common configuration in practice.

The example below uses the parameters from the class docstring — a damper operating at three speeds with `eccentricity_ratio = 0.5`:

In [41]:
from ross.bearings.squeeze_film_damper import SqueezeFilmDamper
from ross.units import Q_

import plotly.io as pio

pio.renderers.default = "notebook"

sfd_groove = SqueezeFilmDamper(
    n=0,  # Node in the FE model of the rotor
    frequency=Q_([18600, 20000, 22000], "rpm"),  # Operating speeds
    axial_length=Q_(0.9, "inches"),  # Damper length
    journal_diameter=Q_(5.1, "inches"),  # Journal diameter
    radial_clearance=Q_(0.003, "inches"),  # Radial clearance
    eccentricity_ratio=0.5,  # Eccentricity ratio (ε = e/c)
    lubricant="ISOVG32",  # Lubricant type
    geometry="groove",  # Central groove, open ends
    cavitation=True,  # Enable cavitation model
)

The `SqueezeFilmDamper` class computes all coefficients analytically during instantiation — no iterative solver is required. The calculation is nearly instantaneous even for a large number of operating speeds.

**Key design parameter:** The `eccentricity_ratio` ε = e/c relates the orbit radius *e* to the radial clearance *c*. For well-behaved operation, values below 0.4 are recommended; higher values increase the nonlinearity of the film forces.

**Execution time**

To display the total computation time, use:

In [42]:
sfd_groove.show_execution_time()

Execution time: 0.000023 seconds


Because the model is analytical, the execution time is typically on the order of microseconds, regardless of the number of frequencies.

## 4.2 Coefficients comparison

To display in table format the damping coefficient `cxx`, stiffness coefficient `kxx`, maximum pressure `p_max`, and pressure angle `theta` for all analyzed speeds, use:

In [43]:
sfd_groove.show_coefficients_comparison()


                                         SFD COEFFICIENTS COMPARISON TABLE                                          
+----------------------+----------------------+----------------------+----------------------+----------------------+
|   Frequency [RPM]    |     cxx [N*s/m]      |      kxx [N/m]       |    Pressure [Pa]     |      Angle [°]       |
+----------------------+----------------------+----------------------+----------------------+----------------------+
|       18600.0        |      2.9571e+04      |      4.2341e+07      |      5.1240e+06      |        214.73        |
|       20000.0        |      2.9571e+04      |      4.5527e+07      |      5.5097e+06      |        214.73        |
|       22000.0        |      2.9571e+04      |      5.0080e+07      |      6.0607e+06      |        214.73        |
+----------------------+----------------------+----------------------+----------------------+----------------------+


The coefficients can also be accessed directly as arrays:

In [44]:
import numpy as np

print("cxx [N·s/m]:", sfd_groove.cxx)
print("kxx [N/m]:  ", sfd_groove.kxx)
print("p_max [Pa]: ", sfd_groove.p_max)
print("theta [deg]:", np.degrees(sfd_groove.theta))

cxx [N·s/m]: [29570.958975694663, 29570.958975694663, 29570.958975694663]
kxx [N/m]:   [42340546.78953549, 45527469.66616719, 50080216.63278392]
p_max [Pa]:  [5124037.9485691  5509718.22426785 6060690.04669464]
theta [deg]: [214.732875 214.732875 214.732875]


>**Note on the stiffness coefficient:** When `cavitation=True`, the oil film is modeled as acting only over the positive-pressure region (π-film model). This eliminates the antisymmetric stiffness cross-coupling term (`kxx = 0`) for the groove geometry. If `cavitation=False`, the full 2π-film model is used, which may produce a non-zero stiffness.

## 4.3 Show results

To display a comprehensive summary table with geometry, operating conditions, and computed coefficients for each analyzed speed, use:

In [45]:
sfd_groove.show_results()


              SQUEEZE FILM DAMPER RESULTS - 18600.0 RPM               
+----------------------+----------------------+----------------------+
| Parameter            |                Value |         Unit         |
+----------------------+----------------------+----------------------+
| Operating Speed      |              18600.0 |         RPM          |
| Geometry Type        |               groove |          -           |
| Cavitation           |                 True |          -           |
| Axial Length         |             0.022860 |          m           |
| Journal Diameter     |             0.129540 |          m           |
| Radial Clearance     |         7.620000e-05 |          m           |
| Eccentricity Ratio   |               0.5000 |          -           |
| Lubricant Viscosity  |           2.7968e-02 |         Pa*s         |
| Damping Coefficient  |           2.9571e+04 |        N*s/m         |
| Stiffness            |           4.2341e+07 |         N/m          |
| Coe

The results table includes:

| Parameter | Description |
|-----------|-------------|
| Operating Speed | Rotational speed [RPM] |
| Geometry Type | `groove`, `end_seals`, or `groove-end_seals` |
| Cavitation | Cavitation model enabled (`True`/`False`) |
| Axial Length | Damper length [m] |
| Journal Radius | Journal radius [m] |
| Radial Clearance | Radial clearance [m] |
| Eccentricity Ratio | ε = e/c [dimensionless] |
| Lubricant Viscosity | Dynamic viscosity at reference temperature [Pa·s] |
| Damping Coefficient | `cxx` [N·s/m] |
| Stiffness Coefficient | `kxx` [N/m] |
| Pressure Angle | θ [° and rad] |
| Maximum Pressure | Peak pressure in the film [Pa] |

## 4.4 End-seal geometry

The end-seal geometry models a damper with sealed ends — oil cannot escape axially. This significantly increases the damping capacity compared to the open-end configuration, but also introduces a non-negligible oil film stiffness.

Note that for the `end_seals` geometry, the stiffness coefficient `kxx` is computed from the Sommerfeld-type analytical expression. With `cavitation=True`, the stiffness term is set to zero (π-film assumption); with `cavitation=False`, the full 2π-film gives `kxx = 0` but doubles the damping.

In [46]:
from ross.bearings.squeeze_film_damper import SqueezeFilmDamper
from ross.units import Q_

sfd_end_seals = SqueezeFilmDamper(
    n=0,
    frequency=Q_([18600, 20000, 22000], "rpm"),
    axial_length=Q_(0.9, "inches"),
    journal_diameter=Q_(5.1, "inches"),
    radial_clearance=Q_(0.003, "inches"),
    eccentricity_ratio=0.5,
    lubricant="ISOVG32",
    geometry="end_seals",  # Sealed ends, no groove
    cavitation=True,
)

sfd_end_seals.show_coefficients_comparison()


                                         SFD COEFFICIENTS COMPARISON TABLE                                          
+----------------------+----------------------+----------------------+----------------------+----------------------+
|   Frequency [RPM]    |     cxx [N*s/m]      |      kxx [N/m]       |    Pressure [Pa]     |      Angle [°]       |
+----------------------+----------------------+----------------------+----------------------+----------------------+
|       18600.0        |      7.5965e+06      |      0.0000e+00      |      2.9333e+08      |        228.76        |
|       20000.0        |      7.5965e+06      |      0.0000e+00      |      3.1541e+08      |        228.76        |
|       22000.0        |      7.5965e+06      |      0.0000e+00      |      3.4695e+08      |        228.76        |
+----------------------+----------------------+----------------------+----------------------+----------------------+


## 4.5 Full results

In [47]:
sfd_end_seals.show_results()


              SQUEEZE FILM DAMPER RESULTS - 18600.0 RPM               
+----------------------+----------------------+----------------------+
| Parameter            |                Value |         Unit         |
+----------------------+----------------------+----------------------+
| Operating Speed      |              18600.0 |         RPM          |
| Geometry Type        |            end_seals |          -           |
| Cavitation           |                 True |          -           |
| Axial Length         |             0.022860 |          m           |
| Journal Diameter     |             0.129540 |          m           |
| Radial Clearance     |         7.620000e-05 |          m           |
| Eccentricity Ratio   |               0.5000 |          -           |
| Lubricant Viscosity  |           2.7968e-02 |         Pa*s         |
| Damping Coefficient  |           7.5965e+06 |        N*s/m         |
| Stiffness            |           0.0000e+00 |         N/m          |
| Coe

## 4.6 Groove with end seals

The `groove-end_seals` geometry combines both features: a central groove for oil supply and sealed ends. This provides the highest load capacity and damping among the three configurations. The formulation is identical to the groove model, but the full film length (not half) is used.

In [48]:
from ross.bearings.squeeze_film_damper import SqueezeFilmDamper
from ross.units import Q_

sfd_groove_seals = SqueezeFilmDamper(
    n=0,
    frequency=Q_([18600, 20000, 22000], "rpm"),
    axial_length=Q_(0.9, "inches"),
    journal_diameter=Q_(5.1, "inches"),
    radial_clearance=Q_(0.003, "inches"),
    eccentricity_ratio=0.5,
    lubricant="ISOVG32",
    geometry="groove-end_seals",  # Central groove + sealed ends
    cavitation=True,
)

sfd_groove_seals.show_coefficients_comparison()


                                         SFD COEFFICIENTS COMPARISON TABLE                                          
+----------------------+----------------------+----------------------+----------------------+----------------------+
|   Frequency [RPM]    |     cxx [N*s/m]      |      kxx [N/m]       |    Pressure [Pa]     |      Angle [°]       |
+----------------------+----------------------+----------------------+----------------------+----------------------+
|       18600.0        |      1.1828e+05      |      1.6936e+08      |      1.0248e+07      |        214.73        |
|       20000.0        |      1.1828e+05      |      1.8211e+08      |      1.1019e+07      |        214.73        |
|       22000.0        |      1.1828e+05      |      2.0032e+08      |      1.2121e+07      |        214.73        |
+----------------------+----------------------+----------------------+----------------------+----------------------+


## 4.7 Comparing geometries

The three geometries produce different coefficient magnitudes for the same bearing dimensions. The comparison below shows the damping coefficient `cxx` at the first speed for each configuration:

In [49]:
print(f"{'Geometry':<22} {'cxx [N·s/m]':>15} {'kxx [N/m]':>15}")
print("-" * 55)
for sfd, name in [
    (sfd_groove, "groove"),
    (sfd_end_seals, "end_seals"),
    (sfd_groove_seals, "groove-end_seals"),
]:
    print(f"{name:<22} {sfd.cxx[0]:>15.4e} {sfd.kxx[0]:>15.4e}")

Geometry                   cxx [N·s/m]       kxx [N/m]
-------------------------------------------------------
groove                      2.9571e+04      4.2341e+07
end_seals                   7.5965e+06      0.0000e+00
groove-end_seals            1.1828e+05      1.6936e+08


## 4.8 Effect of cavitation

When `cavitation=False`, the oil film is assumed to act over the full 360° (2π-film model). This increases the damping for the groove geometry but sets the stiffness to zero regardless. The comparison below illustrates the effect:

In [50]:
from ross.bearings.squeeze_film_damper import SqueezeFilmDamper
from ross.units import Q_

sfd_no_cavitation = SqueezeFilmDamper(
    n=0,
    frequency=Q_([18600, 20000, 22000], "rpm"),
    axial_length=Q_(0.9, "inches"),
    journal_diameter=Q_(5.1, "inches"),
    radial_clearance=Q_(0.003, "inches"),
    eccentricity_ratio=0.5,
    lubricant="ISOVG32",
    geometry="groove",
    cavitation=False,  # Full 2π-film model
)

print(f"{'Model':<25} {'cxx [N·s/m]':>15} {'kxx [N/m]':>15}")
print("-" * 58)
print(
    f"{'groove (cavitation=True)':<25} {sfd_groove.cxx[0]:>15.4e} {sfd_groove.kxx[0]:>15.4e}"
)
print(
    f"{'groove (cavitation=False)':<25} {sfd_no_cavitation.cxx[0]:>15.4e} {sfd_no_cavitation.kxx[0]:>15.4e}"
)

Model                         cxx [N·s/m]       kxx [N/m]
----------------------------------------------------------
groove (cavitation=True)       2.9571e+04      4.2341e+07
groove (cavitation=False)      2.3657e+05      0.0000e+00


## 4.9 Effect of eccentricity ratio

The eccentricity ratio ε = e/c is the most influential parameter on SFD behavior. As ε increases, the damping grows nonlinearly and the stiffness rises sharply. The analysis is repeated for a range of eccentricity ratios to illustrate this sensitivity:

In [51]:
from ross.bearings.squeeze_film_damper import SqueezeFilmDamper
from ross.units import Q_

eccentricity_ratios = [0.1, 0.2, 0.3, 0.4, 0.5, 0.6]

print(f"{'ε':>6} {'cxx [N·s/m]':>15} {'kxx [N/m]':>15} {'p_max [Pa]':>15}")
print("-" * 55)

for eps in eccentricity_ratios:
    sfd = SqueezeFilmDamper(
        n=0,
        frequency=Q_([18600], "rpm"),
        axial_length=Q_(0.9, "inches"),
        journal_diameter=Q_(5.1, "inches"),
        radial_clearance=Q_(0.003, "inches"),
        eccentricity_ratio=eps,
        lubricant="ISOVG32",
        geometry="groove-end_seals",
        cavitation=True,
    )
    print(f"{eps:>6.1f} {sfd.cxx[0]:>15.4e} {sfd.kxx[0]:>15.4e} {sfd.p_max[0]:>15.4e}")

     ε     cxx [N·s/m]       kxx [N/m]      p_max [Pa]
-------------------------------------------------------
   0.1      7.7995e+04      1.9440e+07      7.6879e+05
   0.2      8.1679e+04      4.1348e+07      1.7473e+06
   0.3      8.8502e+04      6.9025e+07      3.2140e+06
   0.4      9.9793e+04      1.0801e+08      5.6727e+06
   0.5      1.1828e+05      1.6936e+08      1.0248e+07
   0.6      1.5005e+05      2.7910e+08      1.9931e+07


## 4.10 Integrating with a rotor model

The `SqueezeFilmDamper` inherits from `BearingElement`, so it can be inserted directly into a `Rotor` assembly like any other bearing element. Its `cxx` and `kxx` coefficients are automatically incorporated into the global damping and stiffness matrices.

A typical SFD installation involves a support spring (squirrel-cage) in series with the damper. In this example a simple rotor is assembled with a radial bearing and an SFD sharing the same node:

In [52]:
from ross.bearings.squeeze_film_damper import SqueezeFilmDamper
from ross.units import Q_

import ross as rs

# Build a simple rotor
steel = rs.Material(name="Steel", rho=7810, E=211e9, G_s=81.2e9)
shaft = [rs.ShaftElement(L=0.25, idl=0, odl=0.05, material=steel) for _ in range(4)]
disk = rs.DiskElement.from_geometry(n=2, material=steel, width=0.07, i_d=0.05, o_d=0.28)

# Stiff radial bearings at the shaft ends
brg0 = rs.BearingElement(n=0, kxx=1e8, cxx=0)
brg4 = rs.BearingElement(n=4, kxx=1e8, cxx=0)

# SFD at node 1 (in addition to the radial bearing stiffness)
sfd = SqueezeFilmDamper(
    n=1,
    frequency=Q_([18600, 20000, 22000], "rpm"),
    axial_length=Q_(0.9, "inches"),
    journal_diameter=Q_(5.1, "inches"),
    radial_clearance=Q_(0.003, "inches"),
    eccentricity_ratio=0.3,
    lubricant="ISOVG32",
    geometry="groove-end_seals",
    cavitation=True,
)

rotor = rs.Rotor(
    shaft_elements=shaft,
    disk_elements=[disk],
    bearing_elements=[brg0, brg4, sfd],
)

# Run modal analysis
modal = rotor.run_modal(speed=0)
print("Natural frequencies [Hz]:", modal.wn[:4] / (2 * 3.14159))

Natural frequencies [Hz]: [104.43319947 104.43319947 379.934484   379.93448401]


## 4.11 Available lubricants

All four THD bearing classes in this tutorial — `PlainJournal`, `TiltingPad`, `ThrustPad`, and `SqueezeFilmDamper` — share the same lubricant interface. The available standard lubricants are:

| Lubricant string | ISO grade | Dynamic viscosity at reference temperature |
|-----------------|-----------|-------------------------------------------|
| `'ISOVG32'` | ISO VG 32 | See `lubricants_dict['ISOVG32']['liquid_viscosity1']` |
| `'ISOVG46'` | ISO VG 46 | See `lubricants_dict['ISOVG46']['liquid_viscosity1']` |
| `'ISOVG68'` | ISO VG 68 | See `lubricants_dict['ISOVG68']['liquid_viscosity1']` |

All four classes also accept a **custom lubricant** by passing a dictionary with the required thermophysical properties to the `lubricant` parameter. The expected keys and format are the same described in [Section 3.14: Available lubricants](#sec-3-14-lubricants).

In [53]:
from ross.bearings.lubricants import lubricants_dict

print(f"{'Lubricant':<12} {'viscosity1 [Pa·s]':>20} {'T1 [K]':>10}")
print("-" * 45)
for name in ["ISOVG32", "ISOVG46", "ISOVG68"]:
    props = lubricants_dict[name]
    print(
        f"{name:<12} {props['liquid_viscosity1']:>20.4e} {props['temperature1']:>10.2f}"
    )

Lubricant       viscosity1 [Pa·s]     T1 [K]
---------------------------------------------
ISOVG32                2.7968e-02     313.15
ISOVG46                3.9693e-02     313.15
ISOVG68                5.7072e-02     313.15


The effect of lubricant grade on the damping coefficient is shown below — heavier oils produce proportionally higher damping:

In [54]:
from ross.bearings.squeeze_film_damper import SqueezeFilmDamper
from ross.units import Q_

print(f"{'Lubricant':<12} {'cxx [N·s/m]':>15} {'p_max [Pa]':>15}")
print("-" * 45)

for grade in ["ISOVG32", "ISOVG46", "ISOVG68"]:
    sfd = SqueezeFilmDamper(
        n=0,
        frequency=Q_([18600], "rpm"),
        axial_length=Q_(0.9, "inches"),
        journal_diameter=Q_(5.1, "inches"),
        radial_clearance=Q_(0.003, "inches"),
        eccentricity_ratio=0.5,
        lubricant=grade,
        geometry="groove-end_seals",
        cavitation=True,
    )
    print(f"{grade:<12} {sfd.cxx[0]:>15.4e} {sfd.p_max[0]:>15.4e}")

Lubricant        cxx [N·s/m]      p_max [Pa]
---------------------------------------------
ISOVG32           1.1828e+05      1.0248e+07
ISOVG46           1.6787e+05      1.4545e+07
ISOVG68           2.4137e+05      2.0913e+07
